In [92]:
import pandas as pd
from pathlib import Path


In [93]:
data_path = Path("/Users/patrykksiazek/Desktop/Machine-Learning---Preliminary-Data-Analysis/Data Preparation and Analysis")

In [94]:
# ...existing code...
from sklearn.model_selection import train_test_split

train_logs = pd.read_csv(data_path / "train_logs.csv")

# split 80/20
X_train_scores, X_test_scores = train_test_split(
    train_logs,
    test_size=0.2,
    random_state=42,
    shuffle=True
)

#optional: write to be able to load them from files during startup
X_train_scores.to_csv(data_path / "X_train_scores.csv", index=False)
X_test_scores.to_csv(data_path / "X_test_scores.csv", index=False)

print("Train:", X_train_scores.shape, "Test:", X_test_scores.shape)
# ...existing code...

Train: (6724718, 11) Test: (1681180, 11)


In [95]:
train_logs.head(10)

,id,event_id,down_time,up_time,action_time,activity,down_event,up_event,text_change,cursor_position,word_count
0,001519c8,1,4526,4557,31,Nonproduction,Leftclick,Leftclick,NoChange,0,0
1,001519c8,2,4558,4962,404,Nonproduction,Leftclick,Leftclick,NoChange,0,0
2,001519c8,3,106571,106571,0,Nonproduction,Shift,Shift,NoChange,0,0
3,001519c8,4,106686,106777,91,Input,q,q,q,1,1
4,001519c8,5,107196,107323,127,Input,q,q,q,2,1
5,001519c8,6,107296,107400,104,Input,q,q,q,3,1
6,001519c8,7,107469,107596,127,Input,q,q,q,4,1
7,001519c8,8,107659,107766,107,Input,q,q,q,5,1
8,001519c8,9,107743,107852,109,Input,q,q,q,6,1
9,001519c8,10,107840,107978,138,Input,Space,Space,,7,1


In [96]:
chars_per_essay = train_logs[train_logs['activity'] == 'Input'].groupby('id').agg(chars_per_essay=('event_id','nunique'))

In [97]:
chars_per_essay

,chars_per_essay
id,
001519c8,2010
0022f953,1938
0042269b,3515
0059420b,1304
0075873a,1942
...,...
ffb8c745,3588
ffbef7e5,2395
ffccd6fd,2849


In [98]:
grouped_train_logs = train_logs.groupby("id").agg(
    words_per_essay=("word_count", "last"),
    max_up_time=("up_time", "max"),
    min_down_time=("down_time", "min"),
    event_per_essay=("event_id", "nunique")
)

In [99]:
grouped_train_logs

,words_per_essay,max_up_time,min_down_time,event_per_essay
id,,,,
001519c8,255,1801969,4526,2557
0022f953,320,1788969,30623,2454
0042269b,404,1771669,4441,4136
0059420b,206,1404469,41395,1556
0075873a,252,1662472,78470,2531
...,...,...,...,...
ffb8c745,273,1791649,22467,4739
ffbef7e5,438,1799174,21732,2604
ffccd6fd,201,1959363,23482,3063


In [100]:
grouped_train_logs ['writing_duration'] = grouped_train_logs['max_up_time'] - grouped_train_logs['min_down_time']

In [101]:
grouped_train_logs = grouped_train_logs.merge(chars_per_essay, left_index=True, right_index=True)

In [102]:
grouped_train_logs['writing_duration'] = grouped_train_logs['max_up_time'] - grouped_train_logs['min_down_time']

In [103]:
grouped_train_logs['chars_per_minute'] = 1000 * 60 * grouped_train_logs['chars_per_essay'] / grouped_train_logs['writing_duration']

### Pauses

In [104]:
train_logs.sort_values(by=['id', 'down_time'], inplace=True)
train_logs['pause_time'] = (train_logs.groupby('id')['down_time'].shift(0) - train_logs.groupby('id')['up_time'].shift(1)).fillna(0)

In [105]:
train_logs

,id,event_id,down_time,up_time,action_time,activity,down_event,up_event,text_change,cursor_position,word_count,pause_time
0,001519c8,1,4526,4557,31,Nonproduction,Leftclick,Leftclick,NoChange,0,0,0.0
1,001519c8,2,4558,4962,404,Nonproduction,Leftclick,Leftclick,NoChange,0,0,1.0
2,001519c8,3,106571,106571,0,Nonproduction,Shift,Shift,NoChange,0,0,101609.0
3,001519c8,4,106686,106777,91,Input,q,q,q,1,1,115.0
4,001519c8,5,107196,107323,127,Input,q,q,q,2,1,419.0
...,...,...,...,...,...,...,...,...,...,...,...,...
8405893,fff05981,3615,2063944,2064440,496,Nonproduction,Leftclick,Leftclick,NoChange,1031,240,1389.0
8405894,fff05981,3616,2064497,2064497,0,Nonproduction,Shift,Shift,NoChange,1031,240,57.0
8405895,fff05981,3617,2064657,2064765,108,Replace,q,q,q => q,1031,240,160.0
8405896,fff05981,3618,2069186,2069259,73,Nonproduction,Leftclick,Leftclick,NoChange,1028,240,4421.0


In [106]:
train_logs['is pause'] = train_logs['pause_time'] > 2000

In [107]:
pause_features = train_logs.groupby('id').agg(
    total_pauses=('pause_time', 'sum'),
    total_pause_time=('pause_time', 'sum')
)

In [108]:
pause_features

,total_pauses,total_pause_time
id,,
001519c8,1500200.0,1500200.0
0022f953,1482955.0,1482955.0
0042269b,1346027.0,1346027.0
0059420b,1173478.0,1173478.0
0075873a,1270300.0,1270300.0
...,...,...
ffb8c745,1269512.0,1269512.0
ffbef7e5,1563221.0,1563221.0
ffccd6fd,1704301.0,1704301.0


In [109]:
grouped_train_logs = grouped_train_logs.merge(pause_features, left_index=True, right_index=True)

In [110]:
grouped_train_logs

,words_per_essay,max_up_time,min_down_time,event_per_essay,writing_duration,chars_per_essay,chars_per_minute,total_pauses,total_pause_time
id,,,,,,,,,
001519c8,255,1801969,4526,2557,1797443,2010,67.095313,1500200.0,1500200.0
0022f953,320,1788969,30623,2454,1758346,1938,66.130329,1482955.0,1482955.0
0042269b,404,1771669,4441,4136,1767228,3515,119.339440,1346027.0,1346027.0
0059420b,206,1404469,41395,1556,1363074,1304,57.399672,1173478.0,1173478.0
0075873a,252,1662472,78470,2531,1584002,1942,73.560513,1270300.0,1270300.0
...,...,...,...,...,...,...,...,...,...
ffb8c745,273,1791649,22467,4739,1769182,3588,121.683354,1269512.0,1269512.0
ffbef7e5,438,1799174,21732,2604,1777442,2395,80.846520,1563221.0,1563221.0
ffccd6fd,201,1959363,23482,3063,1935881,2849,88.300882,1704301.0,1704301.0


In [111]:
grouped_train_logs['perc_pause_time'] = grouped_train_logs['total_pause_time'] / grouped_train_logs['writing_duration']

In [112]:
grouped_train_logs['pauses_per_words'] = grouped_train_logs['total_pauses'] / grouped_train_logs['words_per_essay']

### Activity

In [113]:
train_logs['activity'].value_counts()

activity
Input                                     6726796
Remove/Cut                                 970158
Nonproduction                              703851
Replace                                      4448
Paste                                         599
Move From [1306, 1371] To [1061, 1126]          2
Move From [287, 289] To [285, 287]              1
Move From [460, 461] To [465, 466]              1
Move From [905, 1314] To [907, 1316]            1
Move From [284, 292] To [282, 290]              1
Move From [669, 847] To [565, 743]              1
Move From [1041, 1121] To [1496, 1576]          1
Move From [1455, 1557] To [1323, 1425]          1
Move From [2268, 2275] To [2247, 2254]          1
Move From [213, 302] To [902, 991]              1
Move From [0, 158] To [234, 392]                1
Move From [460, 465] To [925, 930]              1
Move From [565, 743] To [669, 847]              1
Move From [810, 906] To [816, 912]              1
Move From [186, 187] To [184, 185]       

In [114]:
train_logs['activity'].value_counts()

activity
Input                                     6726796
Remove/Cut                                 970158
Nonproduction                              703851
Replace                                      4448
Paste                                         599
Move From [1306, 1371] To [1061, 1126]          2
Move From [287, 289] To [285, 287]              1
Move From [460, 461] To [465, 466]              1
Move From [905, 1314] To [907, 1316]            1
Move From [284, 292] To [282, 290]              1
Move From [669, 847] To [565, 743]              1
Move From [1041, 1121] To [1496, 1576]          1
Move From [1455, 1557] To [1323, 1425]          1
Move From [2268, 2275] To [2247, 2254]          1
Move From [213, 302] To [902, 991]              1
Move From [0, 158] To [234, 392]                1
Move From [460, 465] To [925, 930]              1
Move From [565, 743] To [669, 847]              1
Move From [810, 906] To [816, 912]              1
Move From [186, 187] To [184, 185]       

In [115]:
train_logs['text_change_len'] = train_logs['text_change'].str.len()

In [116]:
train_logs

,id,event_id,down_time,up_time,action_time,activity,down_event,up_event,text_change,cursor_position,word_count,pause_time,is pause,text_change_len
0,001519c8,1,4526,4557,31,Nonproduction,Leftclick,Leftclick,NoChange,0,0,0.0,False,8
1,001519c8,2,4558,4962,404,Nonproduction,Leftclick,Leftclick,NoChange,0,0,1.0,False,8
2,001519c8,3,106571,106571,0,Nonproduction,Shift,Shift,NoChange,0,0,101609.0,True,8
3,001519c8,4,106686,106777,91,Input,q,q,q,1,1,115.0,False,1
4,001519c8,5,107196,107323,127,Input,q,q,q,2,1,419.0,False,1
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
8405893,fff05981,3615,2063944,2064440,496,Nonproduction,Leftclick,Leftclick,NoChange,1031,240,1389.0,False,8
8405894,fff05981,3616,2064497,2064497,0,Nonproduction,Shift,Shift,NoChange,1031,240,57.0,False,8
8405895,fff05981,3617,2064657,2064765,108,Replace,q,q,q => q,1031,240,160.0,False,6
8405896,fff05981,3618,2069186,2069259,73,Nonproduction,Leftclick,Leftclick,NoChange,1028,240,4421.0,True,8


In [117]:
train_logs.loc[train_logs['text_change'] == 'NoChange', 'text_change_len']= 0 

In [118]:
activity_per_essay = {}
activity_columns = {
    'Remove/Cut': ('removes_per_essay', 'removes_len_per_essay'),
    'Nonproduction': ('nonproduction_per_essay', 'nonproduction_len_per_essay'),
    'Replace': ('replaces_per_essay', 'replaces_len_per_essay'),
    'Paste': ('pastes_per_essay', 'pastes_len_per_essay')
}

for act, (count_col, len_col) in activity_columns.items():
    activity_per_essay[act] = train_logs[train_logs['activity'] == act].groupby('id').agg(
        **{
            count_col: ('event_id', 'nunique'),
            len_col: ('text_change_len', 'sum')
        }
    )

activities = list(activity_columns.keys())

In [119]:
activity_per_essay['Remove/Cut']

,removes_per_essay,removes_len_per_essay
id,,
001519c8,417,417
0022f953,260,260
0042269b,439,632
0059420b,151,151
0075873a,517,517
...,...,...
ffb8c745,960,962
ffbef7e5,60,60
ffccd6fd,88,88


In [120]:
old_activity_columns = [
    'activity_per_essay',
    'activity_len_per_essay',
    'activity_per_essay_Nonproduction',
    'activity_len_per_essay_Nonproduction',
    'activity_per_essay_Replace',
    'activity_len_per_essay_Replace',
    'activity_per_essay_Paste',
    'activity_len_per_essay_Paste',
    'removes_per_essay_',
    'removes_len_per_essay_'
]
new_activity_columns = [col for features in activity_per_essay.values() for col in features.columns]

# Clean columns created by previous runs before merging fresh activity features.
grouped_train_logs = grouped_train_logs.loc[:, ~grouped_train_logs.columns.duplicated()]
grouped_train_logs = grouped_train_logs.drop(columns=old_activity_columns + new_activity_columns, errors='ignore')

for act in activities:
    grouped_train_logs = grouped_train_logs.merge(
        activity_per_essay[act],
        left_index=True,
        right_index=True,
        how='left'
    )

In [121]:
grouped_train_logs

,words_per_essay,max_up_time,min_down_time,event_per_essay,writing_duration,chars_per_essay,chars_per_minute,total_pauses,total_pause_time,perc_pause_time,pauses_per_words,removes_per_essay,removes_len_per_essay,nonproduction_per_essay,nonproduction_len_per_essay,replaces_per_essay,replaces_len_per_essay,pastes_per_essay,pastes_len_per_essay
id,,,,,,,,,,,,,,,,,,,
001519c8,255,1801969,4526,2557,1797443,2010,67.095313,1500200.0,1500200.0,0.834630,5883.137255,417.0,417.0,120,0,7.0,107.0,NaN,NaN
0022f953,320,1788969,30623,2454,1758346,1938,66.130329,1482955.0,1482955.0,0.843381,4634.234375,260.0,260.0,254,0,1.0,11.0,1.0,2.0
0042269b,404,1771669,4441,4136,1767228,3515,119.339440,1346027.0,1346027.0,0.761660,3331.750000,439.0,632.0,175,0,7.0,338.0,NaN,NaN
0059420b,206,1404469,41395,1556,1363074,1304,57.399672,1173478.0,1173478.0,0.860906,5696.495146,151.0,151.0,99,0,1.0,17.0,1.0,12.0
0075873a,252,1662472,78470,2531,1584002,1942,73.560513,1270300.0,1270300.0,0.801956,5040.873016,517.0,517.0,72,0,NaN,NaN,NaN,NaN
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
ffb8c745,273,1791649,22467,4739,1769182,3588,121.683354,1269512.0,1269512.0,0.717570,4650.227106,960.0,962.0,189,0,2.0,1004.0,NaN,NaN
ffbef7e5,438,1799174,21732,2604,1777442,2395,80.846520,1563221.0,1563221.0,0.879478,3568.997717,60.0,60.0,148,0,1.0,6.0,NaN,NaN
ffccd6fd,201,1959363,23482,3063,1935881,2849,88.300882,1704301.0,1704301.0,0.880375,8479.109453,88.0,88.0,126,0,NaN,NaN,NaN,NaN


In [122]:
grouped_train_logs.columns[grouped_train_logs.columns.duplicated()]

Index([], dtype='object')

In [123]:
grouped_train_logs['removes_per_words'] = grouped_train_logs['removes_per_essay'] / grouped_train_logs['words_per_essay']

In [124]:
grouped_train_logs['replaces_per_words'] = grouped_train_logs['replaces_per_essay'] / grouped_train_logs['words_per_essay']

In [125]:
grouped_train_logs.fillna(0, inplace=True)

In [126]:
grouped_train_logs.to_csv(data_path / 'grouped_train_logs.csv')

# Analysis

In [127]:
from ydata_profiling import ProfileReport

In [128]:
profile = ProfileReport(grouped_train_logs, title = 'Profiling Report')

In [129]:
profile

Summarize dataset:   0%|          | 0/5 [00:00<?, ?it/s]

100%|██████████| 21/21 [00:00<00:00, 31025.14it/s]


Generate report structure:   0%|          | 0/1 [00:00<?, ?it/s]

Render HTML:   0%|          | 0/1 [00:00<?, ?it/s]

In [130]:
import pandas as pd
import numpy as np
import matplotlib.pyplot as plt
from sklearn.model_selection import train_test_split

%matplotlib inline

# Loading Data

In [131]:
df_scores = pd.read_csv("train_scores.csv")

In [132]:
df_scores

,id,score
0,001519c8,3.5
1,0022f953,3.5
2,0042269b,6.0
3,0059420b,2.0
4,0075873a,4.0
...,...,...
2466,ffb8c745,3.5
2467,ffbef7e5,4.0
2468,ffccd6fd,1.5
2469,ffec5b38,5.0


# Separating the test set

In [133]:
y = df_scores['score']

In [134]:
X_train, X_test, y_train, y_test = train_test_split(df_scores, y, test_size=0.2, stratify=y, random_state=42)

In [135]:
X_train

,id,score
1902,c90ab478,3.5
2370,f599185c,3.5
304,1fb7a3e6,3.5
78,081d84f4,4.0
1162,7a4d1680,4.0
...,...,...
1094,73a14f64,3.5
1922,cb36a061,3.0
1821,bf68655a,4.0
109,0b7d9563,2.5


In [136]:
X_test

,id,score
213,14fee75a,3.5
1018,6aa4881d,3.5
678,488dbe18,4.0
320,21434532,4.0
12,00f8e84c,4.5
...,...,...
697,4994a1b7,3.5
551,3a8c1895,4.0
1335,8c8d7083,3.5
345,230b73d3,3.0


In [137]:
X_train['score'].mean()

np.float64(3.7115384615384617)

In [138]:
X_test['score']

213     3.5
1018    3.5
678     4.0
320     4.0
12      4.5
       ... 
697     3.5
551     4.0
1335    3.5
345     3.0
397     4.5
Name: score, Length: 495, dtype: float64

In [139]:
X_train.to_csv('X_train_scores.csv')
X_test.to_csv('X_test_scores.csv')

## Verification: word_count and time monotonicity

This section checks whether `word_count`, `down_time`, and `up_time` are monotonic within each essay `id` when events are ordered by `event_id`.

In [140]:
logs_ordered = train_logs.sort_values(['id', 'event_id']).copy()

for col in ['word_count', 'down_time', 'up_time']:
    logs_ordered[f'prev_{col}'] = logs_ordered.groupby('id')[col].shift(1)
    logs_ordered[f'diff_{col}'] = logs_ordered[col] - logs_ordered[f'prev_{col}']

word_count_drops = logs_ordered[logs_ordered['diff_word_count'] < 0].copy()

word_count_summary = pd.DataFrame({
    'metric': [
        'total_ids',
        'ids_with_word_count_drop',
        'rows_with_word_count_drop',
        'word_count_is_non_decreasing_for_all_ids'
    ],
    'value': [
        logs_ordered['id'].nunique(),
        word_count_drops['id'].nunique(),
        len(word_count_drops),
        word_count_drops.empty
    ]
})

word_count_summary

,metric,value
0,total_ids,2471
1,ids_with_word_count_drop,2471
2,rows_with_word_count_drop,173861
3,word_count_is_non_decreasing_for_all_ids,False


In [141]:
word_count_drop_context = {
    'activity': word_count_drops['activity'].value_counts().head(10),
    'down_event': word_count_drops['down_event'].value_counts().head(10),
    'up_event': word_count_drops['up_event'].value_counts().head(10)
}

word_count_drop_context

{'activity': activity
 Remove/Cut                                171190
 Replace                                     2657
 Move From [1455, 1557] To [1323, 1425]         1
 Move From [2268, 2275] To [2247, 2254]         1
 Move From [0, 158] To [234, 392]               1
 Move From [810, 906] To [816, 912]             1
 Move From [186, 187] To [184, 185]             1
 Move From [408, 414] To [390, 396]             1
 Move From [1144, 1147] To [1142, 1145]         1
 Move From [747, 960] To [1041, 1254]           1
 Name: count, dtype: int64,
 'down_event': down_event
 Backspace     168938
 q               2288
 Delete          2035
 Space            190
 x                122
 Rightclick        72
 .                 64
 ,                 44
 z                 25
 Enter             14
 Name: count, dtype: int64,
 'up_event': up_event
 Backspace     168938
 Delete          2035
 q               1879
 Space            190
 x                122
 t                 85
 Rightclick        72


In [142]:
word_count_drops[
    [
        'id',
        'event_id',
        'prev_word_count',
        'word_count',
        'diff_word_count',
        'activity',
        'down_event',
        'up_event',
        'text_change'
    ]
].head(20)

,id,event_id,prev_word_count,word_count,diff_word_count,activity,down_event,up_event,text_change
33,001519c8,34,6.0,5,-1.0,Remove/Cut,Backspace,Backspace,q
71,001519c8,72,12.0,11,-1.0,Remove/Cut,Backspace,Backspace,q
74,001519c8,75,11.0,10,-1.0,Remove/Cut,Backspace,Backspace,q
83,001519c8,84,12.0,11,-1.0,Remove/Cut,Backspace,Backspace,q
124,001519c8,125,16.0,15,-1.0,Remove/Cut,Backspace,Backspace,q
140,001519c8,141,17.0,16,-1.0,Remove/Cut,Backspace,Backspace,q
177,001519c8,178,20.0,19,-1.0,Remove/Cut,Backspace,Backspace,q
183,001519c8,184,19.0,18,-1.0,Remove/Cut,Backspace,Backspace,q
195,001519c8,196,21.0,20,-1.0,Remove/Cut,Backspace,Backspace,q
219,001519c8,220,21.0,20,-1.0,Remove/Cut,Backspace,Backspace,q


In [145]:
time_decreases = logs_ordered[
    (logs_ordered['diff_down_time'] < 0) |
    (logs_ordered['diff_up_time'] < 0)
].copy()

time_not_strictly_increasing = logs_ordered[
    (logs_ordered['diff_down_time'] <= 0) |
    (logs_ordered['diff_up_time'] <= 0)
].copy()

time_monotonicity_summary = pd.DataFrame({
    'metric': [
        'total_ids',
        'ids_with_down_time_decrease',
        'ids_with_up_time_decrease',
        'ids_with_down_or_up_time_decrease',
        'worksheet_answer',
        'ids_with_down_or_up_time_not_strictly_increasing'
    ],
    'value': [
        logs_ordered['id'].nunique(),
        logs_ordered.loc[logs_ordered['diff_down_time'] < 0, 'id'].nunique(),
        logs_ordered.loc[logs_ordered['diff_up_time'] < 0, 'id'].nunique(),
        time_decreases['id'].nunique(),
        time_decreases['id'].nunique(),
        time_not_strictly_increasing['id'].nunique()
    ],
    'meaning': [
        'All essay IDs in train_logs',
        'IDs where down_time goes down between consecutive event_id values',
        'IDs where up_time goes down between consecutive event_id values',
        'IDs where down_time or up_time goes down between consecutive event_id values',
        'Correct answer for the worksheet question',
        'Comparison only: includes equal timestamps as well as decreases'
    ]
})

time_monotonicity_summary

,metric,value,meaning
0,total_ids,2471,All essay IDs in train_logs
1,ids_with_down_time_decrease,1,IDs where down_time goes down between consecut...
2,ids_with_up_time_decrease,2213,IDs where up_time goes down between consecutiv...
3,ids_with_down_or_up_time_decrease,2213,IDs where down_time or up_time goes down betwe...
4,worksheet_answer,2213,Correct answer for the worksheet question
5,ids_with_down_or_up_time_not_strictly_increasing,2268,Comparison only: includes equal timestamps as ...
